# 04 Resultaten inlezen en weergeven

In dit script worden de modelresultaten weergegeven en geplot.

In [1]:
import logging
import numpy as np
import pandas as pd
import geopandas as gpd
import hkvsobekpy
from pathlib import Path
import shutil
%matplotlib inline
import matplotlib.pyplot as plt
from shapely.geometry import Point

import plotly.graph_objects as go
from plotly.subplots import make_subplots

In [2]:
%load_ext autoreload
%autoreload 2

The autoreload extension is already loaded. To reload it, use:
  %reload_ext autoreload


### Inlezen meetlocaties en meetdata

Functie voor inlezen csv met afvoermetingen of grondwaterstanden

In [3]:
def inlezen_csv_met_metadata(file_path: Path):
    meta = {}
    with open(file_path, "r", encoding="utf-8") as f:
        lines = f.readlines()

    for line in lines:
        if not line.startswith("#"):
            continue
        text = line.strip("#").strip()
        if ":" in text:
            key, value = text.split(":", 1)
            meta[key.strip()] = value.strip().strip("; ")

    header_idx = next(i for i, line in enumerate(lines) if "Tijdstip (UTC);Waarde" in line)

    df = pd.read_csv(
        file_path,
        sep=";",
        skiprows=header_idx + 1,
        header=None,
        names=["Tijdstip (UTC)", "Waarde"],
        decimal=",",
        skipinitialspace=True
    )

    df["Tijdstip (UTC)"] = pd.to_datetime(df["Tijdstip (UTC)"], utc=True)
    df["time"] = df["Tijdstip (UTC)"].dt.tz_convert("Europe/Amsterdam").dt.tz_localize(None)
    df["Waarde"] = df["Waarde"].replace("---", np.nan).str.replace(",", ".").astype(float)
    df = df.set_index("time")[["Waarde"]]
    df.columns = [csv_file.stem]
    x = float(meta["Postitie X"].split(";")[0].strip("; (RD)"))
    y = float(meta["Postitie Y"].split(";")[0].strip("; (RD)"))

    return meta, Point(x,y), df

In [4]:
main_dir = Path("D:\\153961_Oude_IJssel")
dir_meetdata = Path(main_dir, "WRIJ_RR_Unpaved_methode_01_data\\20260520_meetdata_RR")
dir_afvoermetingen = Path(dir_meetdata, "afvoermetingen_korte_naam")
dir_resultaten = Path(main_dir, "WRIJ_RR_Unpaved_methode_04_resultaten\\1_6_onderzoek_inlooptijd_IMPROVED")

In [5]:
afvoermeetlocaties = gpd.GeoDataFrame()

# afvoermetingen
csv_files = list(dir_afvoermetingen.glob("*.csv"))

afvoermetingen = pd.DataFrame()
for csv_file in csv_files:
    logging.info(f"Data van: {csv_file.stem}")
    meta, point, df = inlezen_csv_met_metadata(csv_file)
    afvoermeetlocaties = pd.concat([
        afvoermeetlocaties, 
        gpd.GeoDataFrame(
            [{"naam": csv_file.stem, "geometry": point}],
            geometry="geometry",
            crs=28992
        )
    ])
    afvoermetingen = pd.merge(afvoermetingen, df[csv_file.stem], how="outer", left_index=True, right_index=True)

afvoermeetlocaties.to_file(Path(dir_afvoermetingen, "afvoermeetlocaties.gpkg"))

In [6]:
fig = make_subplots(rows=1, cols=1)

metingen_instroom = True
metingen = True

columns = [
    'Debietmeting_Kotten_Vosseveldseweg', 
    'Stuw Watermolen Berenschot',
    'Overlaat Berenschotbrug',
    'Overlaat Ulftseweg (Bergeslagbeek)', 
    'Stuw Pelgrim (Waalse Water)',
]

sel_afvoermetingen = afvoermetingen["2015-10":"2016-09"][columns]

for i_station, station in enumerate(sel_afvoermetingen.columns):
    fig.add_trace(
        go.Scatter(
            x=sel_afvoermetingen.index, 
            y=sel_afvoermetingen[station], 
            mode="markers", 
            name=station,
        ),
        row=1, col=1
    )

fig.update_layout(
    template="simple_white",
    title="Gemeten afvoeren",
    margin=dict(l=20, r=20, t=40, b=20),
    height=600,
)
fig.update_xaxes(
    showgrid=True, 
    gridcolor="lightgray", 
)
fig.update_yaxes(
    showgrid=True, 
    gridcolor="lightgray", 
    range=[0, 14]
)
fig.write_html(Path(dir_resultaten, f"oude_ijssel_afvoermetingen.html"), include_plotlyjs="cdn")
fig.show()

In [7]:
afvoermeetlocaties_gebieden = {
    1: {"in": [], "uit": ["Stuw Pelgrim (Waalse Water)"], "gmw_bro_id": []},
    2: {"in": [], "uit": ["Overlaat Ulftseweg (Bergeslagbeek)"], "gmw_bro_id": []},
    3: {"in": ["Debietmeting_Kotten_Vosseveldseweg"], "uit": ["Stuw Watermolen Berenschot"], "gmw_bro_id": []}
    # 3: {"in": ["Debietmeting_Kotten_Vosseveldseweg"], "uit": ["Overlaat Berenschotbrug"], "gmw_bro_id": []}
}

### Selecteer welke modelresultaten (gebieden, scenario’s en periode) worden geanalyseerd

In [8]:
# path to the package containing the data

dir_model_basis = Path(main_dir, "WRIJ_RR_Unpaved_methode_03_modellen")

# gebied = 0 # Oude IJssel
# gebied = 1 # West
# gebied = 2 # Centraal
# gebied = 3 # Oost

gebieden = [1, 2, 3]
scenarios = ["REF"] #, "SCEN"]

# runs = {
#     "OY_0_kD5_L4": {"name": "kD(5d) L=4xl", "color": "#0072B2"},                                        # blauw
#     "OY_1_kD20_L4": {"name": "kD(20d) L=4xl", "color": "#D55E00"},                                      # oranje
#     "OY_2_kD20_L2": {"name": "kD(20d) L=2xl", "color": "#009E73"},                                      # groen
#     "OY_3_kD20_L4_W": {"name": "kD(20d) L=4xl Wh", "color": "#56B4E9"},                                 # lichtblauw
#     "OY_4_kD20_L4_W_InfMax": {"name": "kD(20d) L=2xl Wh InfMax", "color": "#F0E442"},                   # geel
#     "OY_5_kD20_L4_W_InfMax_InitGWS": {"name": "kD(20d) L=2xl Wh InfMax InitGWS", "color": "#E69F00"},   # goud/oranje
# }

# # LONG TEST
# start_date = "2014-07-1"
# end_date = "2016-09-30"
# seizoenen = ["zomer", "winter", "winter", "zomer"]
# date_range = pd.date_range(start_date, end_date, freq="3MS")

# MODELRESULTATEN TBV ONDERZOEK INLOOPTIJD ICM INITIËLE GRONDWATERSTAND

runs = {"OY_5_kD20_L4_W_InfMax_InitGWS_20140101_20160930_IMPROVED": {"name" : "1 jaar inlooptijd", "color" : "#0072B2"},                     # blauw
        "OY_5_kD20_L4_W_InfMax_InitGWS_20130101_20160930_IMPROVED": {"name" : "2 jaar inlooptijd", "color" : "#D55E00"},                     # oranje
        "OY_5_kD20_L4_W_InfMax_InitGWS_20120401_20160930_IMPROVED": {"name" : "2 jaar en 9 maanden inlooptijd", "color" : "#009E73"},        # groen
}

list_start_date = ["2014-01-01", "2013-01-01", "2012-04-01"]
list_end_date = ["2016-09-30", "2016-09-30", "2016-09-30"]
list_seizoenen = [["winter", "zomer", "zomer", "winter"],
                  ["winter", "zomer", "zomer", "winter"],
                  ["zomer", "zomer", "winter", "winter"]]
list_date_range = [pd.date_range(start_date, end_date, freq="3MS") for start_date, end_date in zip(list_start_date, list_end_date)]

In [9]:
simulations_total = pd.DataFrame()

for (i, run_name) in enumerate(runs.keys()):

    start_date = list_start_date[i]
    end_date = list_end_date[i]
    seizoenen = list_seizoenen[i]
    date_range = list_date_range[i]

    for gebied in gebieden:

        for scenario in scenarios:

            simulaties = pd.DataFrame()
            simulaties["start_date"] = date_range
            simulaties["end_date"] = simulaties["start_date"].shift(-1)
            simulaties.loc[simulaties.index[-1],"end_date"] = pd.to_datetime(end_date)
            simulaties["seizoen"] = (seizoenen * 100)[:len(date_range)]
            simulaties["scenario"] = scenario
            simulaties["gebied"] = gebied
            simulaties["run_name"] = run_name
            simulaties["restart_in"] = [0] + [1] * len(simulaties.index[1:])

            simulaties["model_name"] = simulaties.apply(lambda x: f"{run_name[:4]}_gebied{gebied}_{scenario}_rr_{pd.to_datetime(x.start_date).strftime('%Y%m%d')}_{pd.to_datetime(x.end_date).strftime('%Y%m%d')}", axis=1)
            simulations_total = pd.concat([simulations_total, simulaties])

In [10]:
simulations_total.iloc[0:40]

,start_date,end_date,seizoen,scenario,gebied,run_name,restart_in,model_name
0,2014-01-01,2014-04-01,winter,REF,1,OY_5_kD20_L4_W_InfMax_InitGWS_20140101_2016093...,0,OY_5_gebied1_REF_rr_20140101_20140401
1,2014-04-01,2014-07-01,zomer,REF,1,OY_5_kD20_L4_W_InfMax_InitGWS_20140101_2016093...,1,OY_5_gebied1_REF_rr_20140401_20140701
2,2014-07-01,2014-10-01,zomer,REF,1,OY_5_kD20_L4_W_InfMax_InitGWS_20140101_2016093...,1,OY_5_gebied1_REF_rr_20140701_20141001
3,2014-10-01,2015-01-01,winter,REF,1,OY_5_kD20_L4_W_InfMax_InitGWS_20140101_2016093...,1,OY_5_gebied1_REF_rr_20141001_20150101
4,2015-01-01,2015-04-01,winter,REF,1,OY_5_kD20_L4_W_InfMax_InitGWS_20140101_2016093...,1,OY_5_gebied1_REF_rr_20150101_20150401
5,2015-04-01,2015-07-01,zomer,REF,1,OY_5_kD20_L4_W_InfMax_InitGWS_20140101_2016093...,1,OY_5_gebied1_REF_rr_20150401_20150701
6,2015-07-01,2015-10-01,zomer,REF,1,OY_5_kD20_L4_W_InfMax_InitGWS_20140101_2016093...,1,OY_5_gebied1_REF_rr_20150701_20151001
7,2015-10-01,2016-01-01,winter,REF,1,OY_5_kD20_L4_W_InfMax_InitGWS_20140101_2016093...,1,OY_5_gebied1_REF_rr_20151001_20160101
8,2016-01-01,2016-04-01,winter,REF,1,OY_5_kD20_L4_W_InfMax_InitGWS_20140101_2016093...,1,OY_5_gebied1_REF_rr_20160101_20160401
9,2016-04-01,2016-07-01,zomer,REF,1,OY_5_kD20_L4_W_InfMax_InitGWS_20140101_2016093...,1,OY_5_gebied1_REF_rr_20160401_20160701


INLEZEN ALLE RUNS, GEBIEDEN, SCENARIOS

In [11]:
list_total_link_flows = []
list_columns = []

for run, run_dict in runs.items():
    print(run)
    for gebied in gebieden:
        for scenario in scenarios:
            
            simulaties = simulations_total[(simulations_total["run_name"]==run) & (simulations_total["gebied"]==gebied) & (simulations_total["scenario"]==scenario)]
            list_columns.append(f"{run}_{gebied}_{scenario}")

            link_flows = pd.DataFrame()
            for index, simulatie in simulaties.iterrows():
                print(run  + " - " + str(simulatie.gebied) + " - " + simulatie.scenario + " - " + simulatie.model_name)

                dir_model = Path(dir_model_basis, run, f"gebied_{simulatie.gebied}", simulatie.scenario)
                unpaved_rr_file = "3blinks.his"

                path_unpaved_rr_file = Path(dir_model, simulatie.model_name, "rr", unpaved_rr_file)
                if not path_unpaved_rr_file.exists():
                    print(f"File {path_unpaved_rr_file} does not exist. Skipping.")
                    continue
                rr_his = hkvsobekpy.read_his.ReadMetadata(path_unpaved_rr_file)
                rr_results_link_flow = rr_his.DataFrame()['Link flow [m3/s]    ']
                link_flows = pd.concat([link_flows, rr_results_link_flow])
            
            if not link_flows.empty:

                if link_flows.index.duplicated().any():
                    # print(f"Duplicated indices found in link_flows for {run}_{gebied}_{scenario}")
                    link_flows = link_flows[~link_flows.index.duplicated()]
                    # print(f"Removed duplicated indices in link_flows for {run}_{gebied}_{scenario}")

                list_total_link_flows.append(link_flows.sum(axis=1))

total_link_flows = pd.concat(list_total_link_flows, axis=1)
total_link_flows.columns = [column.strip() for column in list_columns]

OY_5_kD20_L4_W_InfMax_InitGWS_20140101_20160930_IMPROVED
OY_5_kD20_L4_W_InfMax_InitGWS_20140101_20160930_IMPROVED - 1 - REF - OY_5_gebied1_REF_rr_20140101_20140401
OY_5_kD20_L4_W_InfMax_InitGWS_20140101_20160930_IMPROVED - 1 - REF - OY_5_gebied1_REF_rr_20140401_20140701
OY_5_kD20_L4_W_InfMax_InitGWS_20140101_20160930_IMPROVED - 1 - REF - OY_5_gebied1_REF_rr_20140701_20141001
OY_5_kD20_L4_W_InfMax_InitGWS_20140101_20160930_IMPROVED - 1 - REF - OY_5_gebied1_REF_rr_20141001_20150101
OY_5_kD20_L4_W_InfMax_InitGWS_20140101_20160930_IMPROVED - 1 - REF - OY_5_gebied1_REF_rr_20150101_20150401
OY_5_kD20_L4_W_InfMax_InitGWS_20140101_20160930_IMPROVED - 1 - REF - OY_5_gebied1_REF_rr_20150401_20150701
OY_5_kD20_L4_W_InfMax_InitGWS_20140101_20160930_IMPROVED - 1 - REF - OY_5_gebied1_REF_rr_20150701_20151001
OY_5_kD20_L4_W_InfMax_InitGWS_20140101_20160930_IMPROVED - 1 - REF - OY_5_gebied1_REF_rr_20151001_20160101
OY_5_kD20_L4_W_InfMax_InitGWS_20140101_20160930_IMPROVED - 1 - REF - OY_5_gebied1_REF_r

In [12]:
total_link_flows

,OY_5_kD20_L4_W_InfMax_InitGWS_20140101_20160930_IMPROVED_1_REF,OY_5_kD20_L4_W_InfMax_InitGWS_20140101_20160930_IMPROVED_2_REF,OY_5_kD20_L4_W_InfMax_InitGWS_20140101_20160930_IMPROVED_3_REF,OY_5_kD20_L4_W_InfMax_InitGWS_20130101_20160930_IMPROVED_1_REF,OY_5_kD20_L4_W_InfMax_InitGWS_20130101_20160930_IMPROVED_2_REF,OY_5_kD20_L4_W_InfMax_InitGWS_20130101_20160930_IMPROVED_3_REF,OY_5_kD20_L4_W_InfMax_InitGWS_20120401_20160930_IMPROVED_1_REF,OY_5_kD20_L4_W_InfMax_InitGWS_20120401_20160930_IMPROVED_2_REF,OY_5_kD20_L4_W_InfMax_InitGWS_20120401_20160930_IMPROVED_3_REF
2012-04-01 00:00:00,NaN,NaN,NaN,NaN,NaN,NaN,0.000000,0.000000,0.000000
2012-04-01 01:00:00,NaN,NaN,NaN,NaN,NaN,NaN,10.330760,6.391384,0.740474
2012-04-01 02:00:00,NaN,NaN,NaN,NaN,NaN,NaN,9.968285,6.248631,0.736589
2012-04-01 03:00:00,NaN,NaN,NaN,NaN,NaN,NaN,9.658612,6.116431,0.733056
2012-04-01 04:00:00,NaN,NaN,NaN,NaN,NaN,NaN,9.383657,5.993104,0.729716
...,...,...,...,...,...,...,...,...,...
2016-09-29 20:00:00,0.030490,0.002764,0.064802,0.030215,0.002757,0.064464,0.030178,0.002756,0.064391
2016-09-29 21:00:00,0.030464,0.002760,0.064772,0.030189,0.002754,0.064433,0.030153,0.002752,0.064361
2016-09-29 22:00:00,0.030439,0.002756,0.064745,0.030164,0.002750,0.064407,0.030128,0.002749,0.064334
2016-09-29 23:00:00,0.030414,0.002753,0.064718,0.030139,0.002746,0.064380,0.030103,0.002745,0.064307


### Plot het resultaat

TODO
- gemeten afvoeren gebied 3
- initiële waterstanden
- L=2x kleine l ipv L = 4x kleine l
- grafieken grondwaterstanden van alle meetpunten plus kaartje
- dynamische grafieken

- grafieken referentie vs scenario: aangepaste kD met initiële grondwaterstanden
- harm maakt overzicht van uren, inspanningen en overdracht.

wibo gaat scenario aanpassen en dan de hele trein weer doen.

In [17]:
start_plot = "2014-01-01"
end_plot = "2016-09-30"

start_date = start_plot
end_date = end_plot

selectie_gebieden = {
    1: {"ymax": 10}, 
    2: {"ymax": 2},
    3: {"ymax": 10},
}

selectie_runs = runs

selectie_scenario = {
    "REF": {"linestyle": "solid", "visible": True}} #, 
#     "SCEN": {"linestyle": "dash", "visible": False},
# }
include_metingen = True

fig = make_subplots(
    rows=len(selectie_gebieden), cols=1,
    shared_xaxes=True,
    vertical_spacing=0.03
)

metingen_instroom = True
metingen = True

for i_gebied, gebied in enumerate(selectie_gebieden.keys()):

    if include_metingen:
        
        instroompunten = afvoermeetlocaties_gebieden[gebied]["in"]
        instroom = afvoermetingen[start_date:end_date][instroompunten].sum(axis=1)
        instroom[instroom<=0.0] = np.nan

        uitstroompunten = afvoermeetlocaties_gebieden[gebied]["uit"]
        uitstroom = afvoermetingen[start_date:end_date][uitstroompunten].sum(axis=1)
        uitstroom[uitstroom<=0.0] = np.nan

        if instroompunten:
            verschil = uitstroom-instroom.shift(4)
            verschil[verschil<=0.0] = np.nan

            fig.add_trace(
                go.Scatter(
                    x=instroom.index, 
                    y=instroom, 
                    mode="markers", 
                    name="Gemeten instroom gebied 3",
                    showlegend=metingen_instroom,
                    legendgroup="uitstroom-instroom",
                    visible="legendonly",
                    marker=dict(color="purple")
                ),
                row=i_gebied+1, col=1
            )
            fig.add_trace(
                go.Scatter(
                    x=uitstroom.index, 
                    y=uitstroom, 
                    mode="markers", 
                    name="Gemeten uitstroom gebied 3",
                    showlegend=metingen_instroom,
                    legendgroup="uitstroom-instroom",
                    visible="legendonly",
                    marker=dict(color="lightgreen")
                ),
                row=i_gebied+1, col=1
            )
            fig.add_trace(
                go.Scatter(
                    x=uitstroom.index, 
                    y=verschil,
                    mode="markers", 
                    name="Afgeleide afvoer gebied 3 (4 uur shift)",
                    showlegend=metingen,
                    visible="legendonly",
                    legendgroup="uitstroom-instroom",
                    marker=dict(color="black")
                ),
                row=i_gebied+1, col=1
            )
            metingen_instroom = False

        if gebied == 3:
            uitstroom = verschil/1.45
            name = f"Afvoer uit gebied {gebied} (afgeleid+gecorrigeerd)"
        else:
            name = f"Afvoer uit gebied {gebied} (metingen)"


        fig.add_trace(
            go.Scatter(
                x=uitstroom.index, 
                y=uitstroom,
                mode="markers", 
                name=name,
                showlegend=metingen,
                legendgroup="metingen",
                marker=dict(color="black")
            ),
            row=i_gebied+1, col=1
        )

for i_gebied, gebied in enumerate(selectie_gebieden.keys()):

    total_link_flows_figure = total_link_flows[start_date:end_date]
    for scenario, scenario_dict in selectie_scenario.items():
        for run, run_dict in selectie_runs.items():
            data = total_link_flows_figure[f"{run}_{gebied}_{scenario}"].copy()
            fig.add_trace(
                go.Scatter(
                    x=data.index, 
                    y=data, 
                    mode="lines", 
                    name=f"{scenario} - {run_dict['name']}",
                    legendgroup=f"{run}_{scenario}",
                    showlegend=True if i_gebied==0 else False,
                    visible=True if (scenario_dict["visible"] and "_restart" in run) else "legendonly",
                    line=dict(dash=scenario_dict["linestyle"], color=run_dict["color"])
                ),
                row=i_gebied+1, col=1
            )

fig.update_layout(
    template="simple_white",
    title="RR-modellering Oude IJssel - Afvoer voor pilotgebieden 1/2/3",
    margin=dict(l=20, r=20, t=40, b=20),
    height=350*len(selectie_gebieden),
    # legend=dict(
    #     groupclick="togglegroup",
    #     orientation="h",
    #     yanchor="top",
    #     y=-0.05,
    #     xanchor="center",
    #     x=0.5,
    #     entrywidth=250,
    #     entrywidthmode="pixels"
    # ),
)

fig.update_xaxes(
    showgrid=True, 
    gridcolor="lightgray", 
    range=[start_plot, end_plot]
)
for i_gebied, (gebied, gebied_dict) in enumerate(selectie_gebieden.items()):
    fig.update_yaxes(
        row=i_gebied+1, 
        col=1, 
        range=[0, gebied_dict["ymax"]],
        showgrid=True,
        gridcolor="lightgray",
        title_text=f"Afvoer gebied {gebied} [m3/s]"
    )

fig.write_html(Path(dir_resultaten, f"oude_ijssel_pilot_gebieden_afvoeren.html"), include_plotlyjs="cdn")
fig.show()